## Checking GPU and Python Environment

In [16]:
import sys
import torch

print("Python version:", sys.version.split()[0])
print("PyTorch version:", torch.__version__)
print("PyTorch CUDA version:", torch.version.cuda)
print("GPU available:", torch.cuda.is_available())

if torch.cuda.is_available():
    print("GPU name:", torch.cuda.get_device_name(0))
else:
    print("Please enable the T4 GPU before continuing.")

print("\n--- NVIDIA GPU Information ---")
!nvidia-smi

Python version: 3.13.16
PyTorch version: 2.11.0+cu130
PyTorch CUDA version: 13.0
GPU available: True
GPU name: Tesla T4

--- NVIDIA GPU Information ---
Thu Oct 29 20:33:08 2026       
+-----------------------------------------------------------------------------------------+
| NVIDIA-SMI 580.82.07              Driver Version: 580.82.07      CUDA Version: 13.0     |
+-----------------------------------------+------------------------+----------------------+
| GPU  Name                 Persistence-M | Bus-Id          Disp.A | Volatile Uncorr. ECC |
| Fan  Temp   Perf          Pwr:Usage/Cap |           Memory-Usage | GPU-Util  Compute M. |
|                                         |                        |               MIG M. |
|=========================================+========================+======================|
|   0  Tesla T4                       Off |   00000000:00:04.0 Off |                    0 |
| N/A   76C    P0             30W /   70W |     703MiB /  15360MiB |      0%    

## Download and Inspect the Official Repository

In [17]:
from pathlib import Path
import subprocess
import os

repo_path = Path("/content/OC_SORT")

if not repo_path.exists():
    subprocess.run(
        ["git", "clone", "https://github.com/noahcao/OC_SORT.git",
         str(repo_path)],
        check=True
    )
else:
    print("Repository folder already exists.")

os.chdir(repo_path)
print("\nWorking folder:", os.getcwd())

print("\n--- Repository Version ---")
subprocess.run(["git", "rev-parse", "HEAD"], check=True)

print("\n--- Required Packages ---")
print(Path("requirements.txt").read_text())

print("\n--- Installation Instructions ---")
install_file = Path("docs/INSTALL.md")
if install_file.exists():
    print(install_file.read_text())
else:
    print("Installation file not found at docs/INSTALL.md.")

Repository folder already exists.

Working folder: /content/OC_SORT

--- Repository Version ---

--- Required Packages ---
# TODO: Update with exact module version
numpy
torch>=1.7
opencv_python
loguru
scikit-image
tqdm
torchvision>=0.10.0
Pillow
thop
ninja
tabulate
tensorboard
lap
# motmetrics # now we use the local and customized version instead
filterpy
h5py

# verified versions
onnx==1.8.1
onnxruntime==1.8.0
onnx-simplifier==0.3.5


--- Installation Instructions ---
## Installation
OC-SORT is built upon codebase of [YOLOX](https://github.com/Megvii-BaseDetection/YOLOX) and [ByteTrack](https://github.com/ifzhang/ByteTrack). I tested the code with Python 3.8. 

### 1. Installing on the host machine
Step1. Install OC-SORT
```shell
git clone https://github.com/noahcao/OC_SORT.git
cd OC_SORT
pip3 install -r requirements.txt
python3 setup.py develop
```

Step2. Install [pycocotools](https://github.com/cocodataset/cocoapi).

```shell
pip3 install cython; pip3 install 'git+https://github.c

## Install Demo Dependencies

In [18]:
import sys
import subprocess

packages = [
    "numpy",
    "scipy",
    "opencv-python",
    "loguru",
    "scikit-image",
    "tqdm",
    "Pillow",
    "thop",
    "ninja",
    "tabulate",
    "tensorboard",
    "lap",
    "filterpy",
    "h5py",
    "cython",
    "pycocotools",
    "cython_bbox",
    "pandas",
    "xmltodict",
    "gdown"
]

subprocess.run(
    [sys.executable, "-m", "pip", "install", *packages],
    check=True
)

print("\nDependency installation completed.")


Dependency installation completed.


## Checking Imports and GPU Operations

In [19]:
import os
import sys
import subprocess

os.chdir("/content/OC_SORT")

check_code = """
import torch
import torchvision
import numpy as np

from torchvision.ops import nms
from trackers.ocsort_tracker.ocsort import OCSort
from yolox.exp import get_exp
from yolox.data.data_augment import preproc
from yolox.utils import fuse_model, get_model_info, postprocess

print("NumPy:", np.__version__)
print("PyTorch:", torch.__version__)
print("Torchvision:", torchvision.__version__)
print("OC-SORT import: PASSED")
print("YOLOX imports: PASSED")

assert torch.cuda.is_available(), "GPU is not available."

x = torch.ones((4, 4), device="cuda")
result = x @ x
torch.cuda.synchronize()
print("GPU calculation: PASSED")

boxes = torch.tensor(
    [[0, 0, 10, 10], [1, 1, 9, 9]],
    dtype=torch.float32,
    device="cuda"
)
scores = torch.tensor([0.9, 0.8], device="cuda")
keep = nms(boxes, scores, 0.5)

print("GPU NMS: PASSED")
print("Kept box indices:", keep.cpu().tolist())
print("All checks passed.")
"""

result = subprocess.run(
    [sys.executable, "-c", check_code],
    capture_output=True,
    text=True
)

print(result.stdout)
if result.stderr:
    print(result.stderr)

if result.returncode != 0:
    print("Check failed. Share the full output before continuing.")

NumPy: 2.1.3
PyTorch: 2.11.0+cu130
Torchvision: 0.26.0+cu130
OC-SORT import: PASSED
YOLOX imports: PASSED
GPU calculation: PASSED
GPU NMS: PASSED
Kept box indices: [0]
All checks passed.



## Finding the Official Pretrained Models

In [20]:
import os
import gdown
from pathlib import Path

os.chdir("/content/OC_SORT")
Path("pretrained").mkdir(exist_ok=True)

folder_url = (
    "https://drive.google.com/drive/folders/"
    "1LnhZVJlpufUnWuObZASIN1KwfhuvT_a8"
)

model_files = gdown.download_folder(
    url=folder_url,
    output="/content/OC_SORT/pretrained/",
    quiet=False,
    skip_download=True
)

if not model_files:
    raise RuntimeError("Could not read the model folder.")

print("\n--- Available Model Files ---")
for item in model_files:
    print(item)

print("\n--- Included Demo Videos ---")
for video in Path("videos").glob("*"):
    if video.is_file():
        print(video.name, "-", round(video.stat().st_size / 1_000_000, 2), "MB")

Retrieving folder contents


Processing file 1Lox1HIT_HOOsPk6nKXuIwg46cap_S27t ocsort_dance_model.pth.tar
Processing file 13PKXXk7VHIO-m8jMWPm-ZhQRuyqNaTMn ocsort_mot17_ablation.pth.tar
Processing file 1b3wGgKn8Ck3Rtzm7p6FE5VlBYPVaZzN4 ocsort_x_mot17.pth.tar
Processing file 1RG8aCO5Kxi_XF_Rbfu58bvDcSdR6_2DU ocsort_x_mot20.pth.tar

--- Available Model Files ---
GoogleDriveFileToDownload(id='1Lox1HIT_HOOsPk6nKXuIwg46cap_S27t', path='ocsort_dance_model.pth.tar', local_path='/content/OC_SORT/pretrained/model_zoo/ocsort_dance_model.pth.tar')
GoogleDriveFileToDownload(id='13PKXXk7VHIO-m8jMWPm-ZhQRuyqNaTMn', path='ocsort_mot17_ablation.pth.tar', local_path='/content/OC_SORT/pretrained/model_zoo/ocsort_mot17_ablation.pth.tar')
GoogleDriveFileToDownload(id='1b3wGgKn8Ck3Rtzm7p6FE5VlBYPVaZzN4', path='ocsort_x_mot17.pth.tar', local_path='/content/OC_SORT/pretrained/model_zoo/ocsort_x_mot17.pth.tar')
GoogleDriveFileToDownload(id='1RG8aCO5Kxi_XF_Rbfu58bvDcSdR6_2DU', path='ocsort_x_mot20.pth.tar', local_path='/content/OC_SORT/pr

Retrieving folder contents completed
Building directory structure
Building directory structure completed
Download completed


## Downloading the DanceTrack Model

In [21]:
from pathlib import Path
import gdown

model_path = Path(
    "/content/OC_SORT/pretrained/ocsort_dance_model.pth.tar"
)

downloaded = gdown.download(
    id="1Lox1HIT_HOOsPk6nKXuIwg46cap_S27t",
    output=str(model_path),
    quiet=False,
    resume=True
)

if downloaded is None or not model_path.is_file():
    raise RuntimeError("Model download failed.")

size_mb = model_path.stat().st_size / (1024 ** 2)

if size_mb < 1:
    raise RuntimeError("Downloaded file is too small. Share the output.")

print("\nModel path:", model_path)
print(f"Model size: {size_mb:.2f} MB")
print("Model download completed.")


Model path: /content/OC_SORT/pretrained/ocsort_dance_model.pth.tar
Model size: 756.11 MB
Model download completed.


Skipping already downloaded file /content/OC_SORT/pretrained/ocsort_dance_model.pth.tar


## Run the Official Demo in Full Precision

In [22]:
import os
import sys
import subprocess
from pathlib import Path

os.chdir("/content/OC_SORT")

official_output = Path(
    "/content/OC_SORT/demo_results/dance_official_fp32.mp4"
)

runner = """
import sys
import runpy
import cv2

sys.path.insert(0, "/content/OC_SORT")
cv2.waitKey = lambda delay=0: -1

sys.argv = [
    "tools/demo_track.py",
    "--demo_type", "video",
    "-f", "exps/example/mot/yolox_dancetrack_test.py",
    "-c", "pretrained/ocsort_dance_model.pth.tar",
    "--path", "videos/dance_demo.mp4",
    "--device", "gpu",
    "--fuse",
    "--save_result",
    "--out_path", "/content/OC_SORT/demo_results/dance_official_fp32.mp4"
]

runpy.run_path("tools/demo_track.py", run_name="__main__")
"""

result = subprocess.run(
    [sys.executable, "-u", "-c", runner],
    stdout=subprocess.PIPE,
    stderr=subprocess.STDOUT,
    text=True
)

print(result.stdout)

if result.returncode != 0:
    raise RuntimeError("Official demo failed. Share the error above.")

if not official_output.exists() or official_output.stat().st_size == 0:
    raise RuntimeError("The output video was not created.")

print("Official FP32 demo completed.")
print("Saved video:", official_output)

2026-10-29 20:33:27.063 | INFO     | __main__:main:226 - Args: Namespace(expn='yolox_dancetrack_test', name=None, dist_backend='nccl', output_dir='evaldata/trackers/mot_challenge', dist_url=None, batch_size=64, devices=None, local_rank=0, num_machines=1, machine_rank=0, exp_file='exps/example/mot/yolox_dancetrack_test.py', fp16=False, fuse=True, trt=False, test=False, speed=False, opts=[], ckpt='pretrained/ocsort_dance_model.pth.tar', conf=0.1, nms=0.7, tsize=None, seed=None, track_thresh=0.6, iou_thresh=0.3, min_hits=3, inertia=0.2, deltat=3, track_buffer=30, match_thresh=0.9, min_box_area=100, gt_type='_val_half', mot20=False, public=False, asso='iou', use_byte=False, raw_results_path='exps/permatrack_kitti_test/', out_path='/content/OC_SORT/demo_results/dance_official_fp32.mp4', dataset='mot', hp=False, demo_type='video', path='videos/dance_demo.mp4', camid=0, save_result=True, aspect_ratio_thresh=1.6, device=device(type='cuda'))
/usr/local/lib/python3.13/dist-packages/torch/functio

## Play the Official FP32 Result

In [23]:
import subprocess
from pathlib import Path
from IPython.display import Video, display

source = Path(
    "/content/OC_SORT/demo_results/dance_official_fp32.mp4"
)
playback = source.with_name("dance_official_fp32_playback.mp4")

result = subprocess.run(
    [
        "ffmpeg", "-y", "-v", "error",
        "-i", str(source),
        "-c:v", "libx264",
        "-preset", "fast",
        "-crf", "23",
        "-pix_fmt", "yuv420p",
        "-movflags", "+faststart",
        "-an",
        str(playback)
    ],
    capture_output=True,
    text=True
)

if result.returncode != 0:
    raise RuntimeError(result.stderr)

print("Official FP32 result:")
display(Video(str(playback), embed=True, width=960))

Official FP32 result:


## Download the Video and Tracking Data

In [24]:
from pathlib import Path
from zipfile import ZipFile, ZIP_DEFLATED
from google.colab import files

video = Path(
    "/content/OC_SORT/demo_results/dance_official_fp32_playback.mp4"
)

tracking_data = Path(
    "/content/OC_SORT/YOLOX_outputs/yolox_dancetrack_test/"
    "track_vis/2026_10_29_20_14_48.txt"
)

for path in [video, tracking_data]:
    if not path.is_file():
        raise FileNotFoundError(f"Missing file: {path}")

zip_path = Path("/content/OC_SORT_official_results.zip")

with ZipFile(zip_path, "w", ZIP_DEFLATED) as archive:
    archive.write(video, arcname="dance_official_fp32.mp4")
    archive.write(tracking_data, arcname="dance_tracks.txt")

print("Download contains:")
print("- dance_official_fp32.mp4")
print("- dance_tracks.txt")

files.download(str(zip_path))

Download contains:
- dance_official_fp32.mp4
- dance_tracks.txt


<IPython.core.display.Javascript object>

<IPython.core.display.Javascript object>